In [1]:
!pip install ../../../PyAlphaShape/.

Defaulting to user installation because normal site-packages is not writeable
Processing /Users/niklasmelton/code/PyAlphaShape
  Installing build dependencies ... done
  Getting requirements to build wheel ... done
  Preparing metadata (pyproject.toml) ... done
  Created wheel for pyalphashape: filename=pyalphashape-0.1.0-py3-none-any.whl size=23261 sha256=804de5e13e926085c784bd265f3bbeec2d7de8b7da7d6a5de456558cbdbf82fb
  Stored in directory: /private/var/folders/60/rg8jprws4px3p6vsl80q8zg00000gn/T/pip-ephem-wheel-cache-pltai6sv/wheels/41/bc/61/9d626df6793fa2c0126903051fc450a88cba0d696fe066517d
Successfully built pyalphashape
  Attempting uninstall: pyalphashape
    Found existing installation: pyalphashape 0.1.0
    Uninstalling pyalphashape-0.1.0:
      Successfully uninstalled pyalphashape-0.1.0

[notice] A new release of pip is available: 24.2 -> 25.1.1
[notice] To update, run: /Library/Developer/CommandLineTools/usr/bin/python3 -m pip install --upgrade pip


In [2]:
!pip install ../../.

Defaulting to user installation because normal site-packages is not writeable
Processing /Users/niklasmelton/code/AdaptiveResonanceLib
  Installing build dependencies ... done
  Getting requirements to build wheel ... done
  Preparing metadata (pyproject.toml) ... done
  Created wheel for artlib: filename=artlib-0.1.3-cp39-cp39-macosx_10_9_universal2.whl size=305595 sha256=c5b0af00ebb0a912d2548d41fdda1f25bd286d106ff7041daddee6013f60e33d
  Stored in directory: /private/var/folders/60/rg8jprws4px3p6vsl80q8zg00000gn/T/pip-ephem-wheel-cache-vkio0a_3/wheels/00/26/74/a797b75203ab88097ff326e33101e51d1788942a404ec4aa0d
Successfully built artlib
  Attempting uninstall: artlib
    Found existing installation: artlib 0.1.3
    Uninstalling artlib-0.1.3:
      Successfully uninstalled artlib-0.1.3

[notice] A new release of pip is available: 24.2 -> 25.1.1
[notice] To update, run: /Library/Developer/CommandLineTools/usr/bin/python3 -m pip install --upgrade pip


In [3]:
import numpy as np
from scipy.spatial import ConvexHull, KDTree

def presort_for_alpha(points: np.ndarray,
                      alpha: float,
                      seed_layer: int = 1) -> np.ndarray:
    """
    Return a reordered copy of `points` that is well‑suited for incremental
    α‑shape construction.

    Parameters
    ----------
    points      : (N,d) array
    alpha       : α used for the shape (needed for the distance window)
    seed_layer  : how many hull layers to peel off before incremental insert

    Returns
    -------
    points_sorted : (N,d) array
    """
    pts = points.copy()
    d   = pts.shape[1]
    r_filter = np.inf if alpha <= 0 else 1.0 / alpha

    seed_idx = []
    remaining = np.arange(len(pts))

    # -------- Stage 1 : convex‑hull peeling --------------------------
    for _ in range(seed_layer):
        if len(remaining) < d + 1:
            break
        hull = ConvexHull(pts[remaining])
        layer = remaining[hull.vertices]
        seed_idx.extend(layer.tolist())
        remaining = np.setdiff1d(remaining, layer, assume_unique=True)

    if len(seed_idx) < d + 1:
        # fall back to random if hull failed (degenerate cloud)
        extra = remaining[: (d + 1 - len(seed_idx))]
        seed_idx.extend(extra.tolist())
        remaining = np.setdiff1d(remaining, extra, assume_unique=True)

    # -------- Stage 2 : sort by distance to hull ---------------------
    if len(remaining):
        hull_pts = pts[seed_idx]
        tree = KDTree(hull_pts)
        dists, _ = tree.query(pts[remaining])
        order = np.argsort(dists)          # closest‑to‑hull first
        remaining = remaining[order]

    # -------- concatenate & return -----------------------------------
    return np.concatenate([seed_idx, remaining])


In [4]:
df["normalzed_continent"].unique()

NameError: name 'df' is not defined

In [3]:
import plotly.graph_objects as go
import numpy as np
import geopandas as gpd
import geodatasets
import numpy as np
from sklearn.datasets import load_iris, make_blobs
import matplotlib.pyplot as plt
from sklearn.datasets import make_moons
import matplotlib.pyplot as plt
from SphericalAlphaART import SphericalAlphaART
from artlib import SimpleARTMAP
import pandas as pd
import reverse_geocoder as rg
from countryinfo import CountryInfo

def gps_to_continent(lat, lon):
    location = rg.search((lat, lon))[0]
    country = location['cc']
    try:
        return CountryInfo(country).info()['region']
    except KeyError:
        return None

df = pd.read_csv("world_capitals.csv")
df = df[~df["normalzed_continent"].isna()]


data = df[["Latitude","Longitude"]].to_numpy()
target = pd.factorize(df['normalzed_continent'])[0]


print("Data has shape:", data.shape)
alpha = 0.0
params = {"rho": 0.0, "alpha": alpha}
art = SphericalAlphaART(**params)

X = art.prepare_data(data)
print("Prepared data has shape:", X.shape)

sorted_idx = np.argsort(target)
# sorted_idx = presort_for_alpha(X, alpha)
X = X[sorted_idx]
target = target[sorted_idx]
df = df.iloc[sorted_idx]

cls = SimpleARTMAP(art)


cls.fit(X, y=target)
y = cls.labels_

print(f"{cls.module_a.n_clusters} clusters found")




# Load the Natural Earth 110m resolution dataset using geodatasets
gdf = gpd.read_file(geodatasets.get_path("naturalearth.land"))

# Extract exterior polygons
coastlines = []
for geom in gdf.geometry:
    if geom.geom_type == 'Polygon':
        x, y = geom.exterior.coords.xy
        coastlines.append((np.array(y), np.array(x)))  # lat, lon
    elif geom.geom_type == 'MultiPolygon':
        for poly in geom.geoms:
            x, y = poly.exterior.coords.xy
            coastlines.append((np.array(y), np.array(x)))  # lat, lon

# Function to convert lat/lon to unit sphere coordinates
def latlon_to_xyz(lat, lon):
    lat = np.radians(lat)
    lon = np.radians(lon)
    x = np.cos(lat) * np.cos(lon)
    y = np.cos(lat) * np.sin(lon)
    z = np.sin(lat)
    return x, y, z

# Create 3D globe surface
u, v = np.mgrid[0:2*np.pi:100j, 0:np.pi:50j]
xs = np.cos(u) * np.sin(v)
ys = np.sin(u) * np.sin(v)
zs = np.cos(v)

fig = go.Figure()

# Add faint sphere background
fig.add_trace(go.Surface(
    x=xs, y=ys, z=zs,
    colorscale='Greys',
    opacity=0.5,
    showscale=False
))

# Add continent outlines
for lat, lon in coastlines:
    x, y, z = latlon_to_xyz(lat, lon)
    fig.add_trace(go.Scatter3d(
        x=x, y=y, z=z,
        mode='lines',
        line=dict(color='black', width=1),
        showlegend=False
    ))

# Clean up scene
fig.update_layout(
    scene=dict(
        xaxis=dict(visible=False),
        yaxis=dict(visible=False),
        zaxis=dict(visible=False),
        aspectmode='data',
    ),
    margin=dict(l=0, r=0, t=0, b=0)
)

import plotly.graph_objects as go
from matplotlib.pyplot import cm
from pyalphashape import plot_spherical_alpha_shape
colors = cm.rainbow(np.linspace(0, 6, cls.module_a.n_clusters))
for c, w in zip(colors, cls.module_a.W):
    fig = plot_spherical_alpha_shape(
        w, fig=fig, line_width=3, line_color="red", fill=False
    )

# ────── ADD DATA‑POINTS COLOURED BY CONTINENT ──────
continent_colors = {
    "Asia":     "#1f77b4",   # blue
    "Africa":   "#ff7f0e",   # orange
    "Europe":   "#2ca02c",   # green
    "Oceania":  "#d62728",   # red
    "Americas": "#9467bd",   # purple
}

for cont, hexcol in continent_colors.items():
    mask = df["normalzed_continent"] == cont
    if not mask.any():        # skip if that continent isn’t present
        continue
    lat_c = df.loc[mask, "Latitude"].to_numpy()
    lon_c = df.loc[mask, "Longitude"].to_numpy()
    x_c, y_c, z_c = latlon_to_xyz(lat_c, lon_c)

    fig.add_trace(
        go.Scatter3d(
            x=x_c, y=y_c, z=z_c,
            mode="markers",
            marker=dict(size=4, color=hexcol, opacity=0.9),
            name=cont          # shows up in legend
        )
    )
# ────────────────────────────────────────────────────



fig.show()

Data has shape: (189, 2)
Prepared data has shape: (189, 2)
5 clusters found


/Users/niklasmelton/Library/Python/3.9/lib/python/site-packages/urllib3/__init__.py:35: NotOpenSSLWarning:

urllib3 v2 only supports OpenSSL 1.1.1+, currently the 'ssl' module is compiled with 'LibreSSL 2.8.3'. See: https://github.com/urllib3/urllib3/issues/3020



In [4]:
cls.W[0].perimeter_points

array([[-0.1949311 ,  0.64119143,  0.74220982],
       [-0.28224609,  0.95345789, -0.10609053],
       [ 0.53477001,  0.52551703,  0.66170453],
       [-0.4742376 ,  0.77206944,  0.42309275],
       [ 0.17393335,  0.97744436,  0.11979029],
       [-0.4542573 ,  0.62961163,  0.63026938],
       [ 0.67463564,  0.4933971 ,  0.54902282],
       [ 0.56535187,  0.70693789,  0.42498952],
       [-0.47399509,  0.63870059,  0.60612723]])

In [7]:
cls = SphericalAlphaART(rho=0.,alpha=0.0)

In [8]:
cls.fit(X_test[:4])

SphericalAlphaART(alpha=0.0, rho=0.0)

In [9]:
cls.n_clusters

1

In [10]:
[cls.category_choice(X_test[4], w, {"rho":0.0, "alpha":0.0}) for w in cls.W]

[(0.7670916441685557, {'internal': False})]

In [1]:
import plotly.graph_objects as go
import numpy as np
import geopandas as gpd
import geodatasets
import numpy as np
from sklearn.datasets import load_iris, make_blobs
import matplotlib.pyplot as plt
from sklearn.datasets import make_moons
import matplotlib.pyplot as plt
from pyalphashape import SphericalAlphaShape
from artlib import SimpleARTMAP
import pandas as pd
import reverse_geocoder as rg
from countryinfo import CountryInfo
from copy import deepcopy

def gps_to_continent(lat, lon):
    location = rg.search((lat, lon))[0]
    country = location['cc']
    try:
        return CountryInfo(country).info()['region']
    except KeyError:
        return None

df = pd.read_csv("world_capitals.csv")
df = df[~df["normalzed_continent"].isna()]


data = df[["Latitude","Longitude"]].to_numpy()
target = pd.factorize(df['normalzed_continent'])[0]


print("Data has shape:", data.shape)

X = data
print("Prepared data has shape:", X.shape)

sorted_idx = np.argsort(target)
# sorted_idx = presort_for_alpha(X, alpha)
# X = X[sorted_idx]
# target = target[sorted_idx]

X = X[target==0]
init_data = np.zeros((0,2))
shape = SphericalAlphaShape(init_data)
for x in X:
    shape = deepcopy(shape)
    shape.add_points(x.reshape((1,-1)))



# Load the Natural Earth 110m resolution dataset using geodatasets
gdf = gpd.read_file(geodatasets.get_path("naturalearth.land"))

# Extract exterior polygons
coastlines = []
for geom in gdf.geometry:
    if geom.geom_type == 'Polygon':
        x, y = geom.exterior.coords.xy
        coastlines.append((np.array(y), np.array(x)))  # lat, lon
    elif geom.geom_type == 'MultiPolygon':
        for poly in geom.geoms:
            x, y = poly.exterior.coords.xy
            coastlines.append((np.array(y), np.array(x)))  # lat, lon

# Function to convert lat/lon to unit sphere coordinates
def latlon_to_xyz(lat, lon):
    lat = np.radians(lat)
    lon = np.radians(lon)
    x = np.cos(lat) * np.cos(lon)
    y = np.cos(lat) * np.sin(lon)
    z = np.sin(lat)
    return x, y, z

# Create 3D globe surface
u, v = np.mgrid[0:2*np.pi:100j, 0:np.pi:50j]
xs = np.cos(u) * np.sin(v)
ys = np.sin(u) * np.sin(v)
zs = np.cos(v)

fig = go.Figure()

# Add faint sphere background
fig.add_trace(go.Surface(
    x=xs, y=ys, z=zs,
    colorscale='Greys',
    opacity=0.5,
    showscale=False
))

# Add continent outlines
for lat, lon in coastlines:
    x, y, z = latlon_to_xyz(lat, lon)
    fig.add_trace(go.Scatter3d(
        x=x, y=y, z=z,
        mode='lines',
        line=dict(color='black', width=1),
        showlegend=False
    ))

# Clean up scene
fig.update_layout(
    scene=dict(
        xaxis=dict(visible=False),
        yaxis=dict(visible=False),
        zaxis=dict(visible=False),
        aspectmode='data',
    ),
    margin=dict(l=0, r=0, t=0, b=0)
)

import plotly.graph_objects as go
from matplotlib.pyplot import cm
from pyalphashape import plot_spherical_alpha_shape
colors = cm.rainbow(np.linspace(0, 6, 5))
for c, w in zip(colors, [shape]):
    fig = plot_spherical_alpha_shape(
        w, fig=fig, line_width=3, line_color="red", fill=False
    )

# ────── ADD DATA‑POINTS COLOURED BY CONTINENT ──────
continent_colors = {
    "Asia":     "#1f77b4",   # blue
    "Africa":   "#ff7f0e",   # orange
    "Europe":   "#2ca02c",   # green
    "Oceania":  "#d62728",   # red
    "Americas": "#9467bd",   # purple
}

for cont, hexcol in continent_colors.items():
    mask = df["normalzed_continent"] == cont
    if not mask.any():        # skip if that continent isn’t present
        continue
    lat_c = df.loc[mask, "Latitude"].to_numpy()
    lon_c = df.loc[mask, "Longitude"].to_numpy()
    x_c, y_c, z_c = latlon_to_xyz(lat_c, lon_c)

    fig.add_trace(
        go.Scatter3d(
            x=x_c, y=y_c, z=z_c,
            mode="markers",
            marker=dict(size=4, color=hexcol, opacity=0.9),
            name=cont          # shows up in legend
        )
    )
# ────────────────────────────────────────────────────



fig.show()

Data has shape: (189, 2)
Prepared data has shape: (189, 2)
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here
here


/Users/niklasmelton/Library/Python/3.9/lib/python/site-packages/urllib3/__init__.py:35: NotOpenSSLWarning:

urllib3 v2 only supports OpenSSL 1.1.1+, currently the 'ssl' module is compiled with 'LibreSSL 2.8.3'. See: https://github.com/urllib3/urllib3/issues/3020



In [11]:
X[0]

array([24.28, 54.22])